# Exploration of Catchment Areas

In [1]:
from pathlib import Path
import fiona

gdb = Path(
    "/courses/DS5500.202710/teams/team4/data/processed/"
    "nhdplus_extracted/NHDPLUS_H_19020401_HU8_GDB/"
    "NHDPLUS_H_19020401_HU8_GDB.gdb"
)

print("Geodatabase exists:", gdb.exists())

layers = fiona.listlayers(str(gdb))

print(f"Found {len(layers)} feature classes/layers:\n")
for layer in layers:
    print(layer)

Geodatabase exists: True
Found 86 feature classes/layers:

ExternalCrosswalk
FeatureToMetadata
HUMod
NHDFCode
NHDFeatureToMetadata
NHDMetadata
NHDPlusDivFracMP
NHDPlusEROMMA
NHDPlusEROMQAMA
NHDPlusEROMQARPT
NHDPlusFlow
NHDPlusFlowlineVAA
NHDPlusIncrLat
NHDPlusIncrPrecipMA
NHDPlusIncrPrecipMM01
NHDPlusIncrPrecipMM02
NHDPlusIncrPrecipMM03
NHDPlusIncrPrecipMM04
NHDPlusIncrPrecipMM05
NHDPlusIncrPrecipMM06
NHDPlusIncrPrecipMM07
NHDPlusIncrPrecipMM08
NHDPlusIncrPrecipMM09
NHDPlusIncrPrecipMM10
NHDPlusIncrPrecipMM11
NHDPlusIncrPrecipMM12
NHDPlusIncrROMA
NHDPlusIncrTempMA
NHDPlusIncrTempMM01
NHDPlusIncrTempMM02
NHDPlusIncrTempMM03
NHDPlusIncrTempMM04
NHDPlusIncrTempMM05
NHDPlusIncrTempMM06
NHDPlusIncrTempMM07
NHDPlusIncrTempMM08
NHDPlusIncrTempMM09
NHDPlusIncrTempMM10
NHDPlusIncrTempMM11
NHDPlusIncrTempMM12
NHDPlusMegaDiv
NHDPlusNHDPlusIDGridCode
NHDProcessingParameters
NHDReachCodeMaintenance
NHDReachCrossReference
NHDSourceCitation
NHDVerticalRelationship
ProcessingParameters
NHDPlusBurnLine

In [2]:
keywords = ["catchment", "flowline", "flow", "waterbody"]

for layer in layers:
    if any(word in layer.lower() for word in keywords):
        print(layer)

NHDPlusFlow
NHDPlusFlowlineVAA
NHDPlusBurnWaterbody
NHDPlusCatchment
NHDFlowline
NHDWaterbody


In [3]:
import geopandas as gpd

catchment_layer = next(
    layer for layer in layers
    if "catchment" in layer.lower()
)

catchments = gpd.read_file(
    gdb,
    layer=catchment_layer,
    rows=5,
)

print("Layer:", catchment_layer)
print("CRS:", catchments.crs)
print("Geometry type:", catchments.geom_type.value_counts().to_dict())
print("Columns:")
print(catchments.columns.tolist())

catchments.head()

Layer: NHDPlusCatchment
CRS: EPSG:4269
Geometry type: {'MultiPolygon': 5}
Columns:
['NHDPlusID', 'SourceFC', 'GridCode', 'AreaSqKm', 'VPUID', 'SHAPE_Length', 'SHAPE_Area', 'geometry']


,NHDPlusID,SourceFC,GridCode,AreaSqKm,VPUID,SHAPE_Length,SHAPE_Area,geometry
0,7.500010e+13,NHDPlusBurnLineEvent,3951,0.889125,19020401,0.070380,0.000151,"MULTIPOLYGON (((-149.10038 61.74846, -149.1003..."
1,7.500010e+13,NHDPlusBurnLineEvent,3031,0.085800,19020401,0.038948,0.000014,"MULTIPOLYGON (((-149.39975 61.16974, -149.3997..."
2,7.500010e+13,NHDPlusBurnLineEvent,3049,0.035075,19020401,0.034374,0.000006,"MULTIPOLYGON (((-149.67949 61.08849, -149.6791..."
3,7.500010e+13,NHDPlusBurnLineEvent,3109,0.220500,19020401,0.050742,0.000037,"MULTIPOLYGON (((-149.50733 61.16181, -149.5073..."
4,7.500010e+13,NHDPlusBurnLineEvent,3112,0.181450,19020401,0.059027,0.000030,"MULTIPOLYGON (((-149.45034 61.229, -149.4508 6..."


## Now map only relevant catchment areas to pilot with streams/water quality stations/dam removal

In [17]:
from pathlib import Path

import folium
import geopandas as gpd
import pandas as pd
import branca.colormap as cm

# Load reaches displayed on the stream map
reach_table = pd.read_csv(
    "../data/processed/catchment_relationship_reaches.csv"
)

reach_table["NHDPlusID"] = reach_table["NHDPlusID"].astype("int64")

gdb_path = (
    Path("../data/processed/nhdplus_extracted")
    / f"NHDPLUS_H_19020401_HU8_GDB"
    / f"NHDPLUS_H_19020401_HU8_GDB.gdb"
)

# Load local catchment polygons
catchments = gpd.read_file(
    gdb_path,
    layer="NHDPlusCatchment",
)

catchments["NHDPlusID"] = pd.to_numeric(
    catchments["NHDPlusID"],
    errors="coerce",
).astype("Int64")

# Keep only catchments corresponding to displayed stream reaches
catchments = catchments[
    catchments["NHDPlusID"].isin(reach_table["NHDPlusID"])
].copy()

# Attach upstream/downstream relationship to each catchment
catchments = catchments.merge(
    reach_table[["NHDPlusID", "relationship"]],
    on="NHDPlusID",
    how="inner",
    validate="one_to_one",
)

print(catchments["relationship"].value_counts())

print(f"Stream reaches in map: {len(reach_table):,}")
print(f"Matching catchment polygons: {len(catchments):,}")
print(
    "Reaches without a catchment:",
    len(reach_table) - len(catchments),
)

relationship
upstream      391
downstream     35
same reach      1
Name: count, dtype: int64
Stream reaches in map: 427
Matching catchment polygons: 427
Reaches without a catchment: 0


In [21]:
import geopandas as gpd
import folium
import branca.colormap as cm
from pathlib import Path

layers_path = Path("../data/processed/catchment_map_layers.gpkg")

streams = gpd.read_file(layers_path, layer="streams").to_crs("EPSG:4326")
stations = gpd.read_file(layers_path, layer="stations").to_crs("EPSG:4326")
dam_gdf = gpd.read_file(layers_path, layer="dam").to_crs("EPSG:4326")

catchments = catchments.to_crs("EPSG:4326")

# Use the catchment extent to center the map
minx, miny, maxx, maxy = catchments.total_bounds

m = folium.Map(
    location=[(miny + maxy) / 2, (minx + maxx) / 2],
    zoom_start=10,
    tiles="OpenStreetMap",
)


folium.GeoJson(
    catchments,
    name="Local catchment areas",
    style_function=lambda feature: {
        "fillColor": "#0000ee",
        "color": "#666666",
        "weight": 0.5,
        "fillOpacity": 0.15,
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["NHDPlusID", "AreaSqKm", "relationship"],
        aliases=[
            "Reach ID:",
            "Catchment area (km²):",
            "Relationship to dam:",
        ],
    ),
).add_to(m)

# Overlay stream reaches
streams_map = streams.copy()

# Drop datetime columns that Folium cannot serialize
datetime_cols = streams_map.select_dtypes(
    include=["datetime", "datetimetz"]
).columns

streams_map = streams_map.drop(columns=datetime_cols)

folium.GeoJson(
    streams_map,
    name="Stream reaches",
    style_function=lambda feature: {
        "color": "#2171B5",
        "weight": 2.5,
        "opacity": 1.0,
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["NHDPlusID", "signed_distance_km"],
        aliases=["Reach ID:", "Distance from dam (km):"],
    ),
).add_to(m)

# Overlay water-quality stations
for _, station in stations.iterrows():
    if station.geometry is None or station.geometry.is_empty:
        continue

    folium.CircleMarker(
        location=[station.geometry.y, station.geometry.x],
        radius=4,
        color="#7B3294",
        fill=True,
        fill_color="#C2A5CF",
        fill_opacity=0.95,
        tooltip=str(
            station.get("MonitoringLocationIdentifier", "Water-quality station")
        ),
    ).add_to(m)

# Overlay selected dam removal
for _, row in dam_gdf.iterrows():
    folium.Marker(
        location=[row.geometry.y, row.geometry.x],
        tooltip=f"{row['dam_name']} ({row['year_removed']})",
        icon=folium.Icon(color="red", icon="flag"),
    ).add_to(m)


folium.LayerControl().add_to(m)
m.fit_bounds([[miny, minx], [maxy, maxx]])

m

So, for our dam removal, we now have all relevant stream reaches with water quality stations as well as all relevant catchment areas. These catchment areas can now be used to get relevant land cover and climate data!